In [1]:
%pip install folium shapely

  Using cached jinja2-3.1.6-py3-none-any.whl.metadata (2.9 kB)
   ---------------------------------------- 0.0/1.8 MB ? eta -:--:--
   ---------------------------------------- 1.8/1.8 MB 20.6 MB/s  0:00:00
Using cached jinja2-3.1.6-py3-none-any.whl (134 kB)
   ---------------------------------------- 0.0/12.7 MB ? eta -:--:--
   ------------ --------------------------- 3.9/12.7 MB 19.6 MB/s eta 0:00:01
   -------------------- ------------------- 6.6/12.7 MB 16.2 MB/s eta 0:00:01
   ----------------------------- ---------- 9.4/12.7 MB 15.1 MB/s eta 0:00:01
   ------------------------------------- -- 12.1/12.7 MB 14.6 MB/s eta 0:00:01
   ---------------------------------------- 12.7/12.7 MB 14.2 MB/s  0:00:00

   --- ------------------------------------  1/12 [urllib3]
   ------ ---------------------------------  2/12 [numpy]
   ------ ---------------------------------  2/12 [numpy]
   ------ ---------------------------------  2/12 [numpy]
   ------ ---------------------------------  2/1

  Consider adding this directory to PATH or, if you prefer to suppress this warning, use --no-warn-script-location.
  Consider adding this directory to PATH or, if you prefer to suppress this warning, use --no-warn-script-location.
  Consider adding this directory to PATH or, if you prefer to suppress this warning, use --no-warn-script-location.

[notice] A new release of pip is available: 26.0.1 -> 26.2.1
[notice] To update, run: C:\Users\Kim\AppData\Local\Python\pythoncore-3.14-64\python.exe -m pip install --upgrade pip


In [3]:
import json
from pathlib import Path
from collections import Counter
from html import escape

import folium
from folium.plugins import MarkerCluster, Fullscreen
from shapely.geometry import shape
from IPython.display import display

# The GeoJSON should be in the same directory as this notebook.
GEOJSON_PATH = Path('export.geojson')

# Switch this to False if you want to see no markers when the file is empty.
USE_DEMO_IF_EMPTY = True

with GEOJSON_PATH.open(encoding='utf-8') as f:
    geojson = json.load(f)

if geojson.get('type') != 'FeatureCollection':
    raise ValueError('Expected a GeoJSON FeatureCollection')

features = geojson.get('features', [])
print(f'Loaded {len(features):,} GeoJSON features from {GEOJSON_PATH}')

Loaded 4,234 GeoJSON features from export.geojson


In [4]:
# Demo fallback: locations and values copied from the Overpass CSV excerpt in the chat.
# These are not visitors, popularity scores or a complete POI dataset.
demo_rows = [
    ('Gamla stan', 59.3249529, 18.0706429, 'tourism', 'attraction'),
    ('Moderna museet', 59.3263494, 18.0840004, 'tourism', 'museum'),
    ('Naturhistoriska riksmuseet', 59.3690466, 18.0540033, 'tourism', 'museum'),
    ('Kungliga Operan', 59.3296435, 18.0699588, 'amenity', 'theatre'),
    ('Kvarnen', 59.3148328, 18.0742292, 'amenity', 'restaurant'),
    ('Nobelprismuseet', 59.3252155, 18.0708309, 'tourism', 'museum'),
    ('Tudor Arms', 59.3348944, 18.0853465, 'amenity', 'pub'),
]

if not features and USE_DEMO_IF_EMPTY:
    features = [
        {'type': 'Feature',
         'geometry': {'type': 'Point', 'coordinates': [lon, lat]},
         'properties': {'name': name, field: category, 'source': 'Demo — user-provided CSV excerpt'}}
        for name, lat, lon, field, category in demo_rows
    ]
    demo_mode = True
    print('DEMO MODE: using 7 selected places copied from your CSV excerpt.')
else:
    demo_mode = False

print('Markers available:', len(features))

Markers available: 4234


In [12]:
def classify(properties):
    for field in ('tourism', 'historic', 'amenity', 'leisure', 'shop', 'railway', 'public_transport'):
        value = properties.get(field)
        if value:
            return field, str(value)
    return 'other', 'other'

COLORS = {
    'tourism': 'blue', 'historic': 'purple', 'amenity': 'orange',
    'leisure': 'green', 'shop': 'cadetblue', 'railway': 'red',
    'public_transport': 'darkred', 'other': 'gray'
}

import folium

m = folium.Map(
    location=[59.3293, 18.0686],
    zoom_start=12,
    tiles=None
)

folium.TileLayer(
    tiles="https://server.arcgisonline.com/ArcGIS/rest/services/World_Street_Map/MapServer/tile/{z}/{y}/{x}",
    attr="Tiles © Esri",
    name="Esri World Street Map",
    overlay=False,
    control=True
).add_to(m)
Fullscreen().add_to(m)
cluster = MarkerCluster(name='Places (hover to inspect)', show=True).add_to(m)

coordinates = []
categories = Counter()
skipped = 0
for feat in features:
    geom = feat.get('geometry')
    if not geom:
        skipped += 1
        continue
    try:
        point = shape(geom).representative_point()
        lat, lon = point.y, point.x
        if not (-90 <= lat <= 90 and -180 <= lon <= 180):
            raise ValueError('Invalid coordinate')
    except (TypeError, ValueError, KeyError):
        skipped += 1
        continue

    props = feat.get('properties') or {}
    group, category = classify(props)
    categories[group] += 1
    name = str(props.get('name') or props.get('name:en') or 'Unnamed location')
    shown_category = f'{group}: {category}'

    # All available properties in a clickable detail popup.
    rows = ''.join(
        f'<tr><th style="text-align:left;padding:4px 10px 4px 0">{escape(str(k))}</th>'
        f'<td style="padding:4px">{escape(str(v))}</td></tr>'
        for k, v in props.items() if v is not None and v != ''
    )
    popup_html = (
        f'<div style="max-height:270px;overflow:auto;font-family:sans-serif">'
        f'<b>{escape(name)}</b><p>{escape(shown_category)}</p>'
        f'<table>{rows}</table>'
        f'<small>Coordinates: {lat:.6f}, {lon:.6f}</small></div>'
    )
    tooltip_html = f'<b>{escape(name)}</b><br>{escape(shown_category)}'
    folium.Marker(
        location=[lat, lon],
        tooltip=folium.Tooltip(tooltip_html, sticky=True),
        popup=folium.Popup(popup_html, max_width=440),
        icon=folium.Icon(color=COLORS.get(group, 'gray'), icon='info-sign'),
    ).add_to(cluster)
    coordinates.append([lat, lon])

if coordinates and not demo_mode:
    m.fit_bounds([list(map(min, zip(*coordinates))), list(map(max, zip(*coordinates)))])

folium.LayerControl().add_to(m)
print('Plotted:', len(coordinates), '| skipped invalid geometries:', skipped)
print('Categories:', dict(categories))
if demo_mode:
    print('NOTE: DEMO MAP — source GeoJSON was empty.')

display(m)

Plotted: 4234 | skipped invalid geometries: 0
Categories: {'historic': 197, 'tourism': 705, 'leisure': 526, 'amenity': 2806}


In [13]:
# Save a standalone, interactive HTML map that opens in any browser.
output = Path('stockholm_poi_map.html')
m.save(str(output))
print('Saved:', output.resolve())
print('If the map contains too many markers, consider filtering categories before plotting.')

Saved: C:\Users\Kim\software engineering\year 5\LP1\4DT911\test\stockholm_poi_map.html
If the map contains too many markers, consider filtering categories before plotting.


In [14]:
import webbrowser
from pathlib import Path

map_path = Path("stockholm_poi_map.html").resolve()

webbrowser.open(map_path.as_uri())

True

In [16]:
%pip install geopandas

   ---------------------------------------- 0.0/9.8 MB ? eta -:--:--
   ---------------- ----------------------- 3.9/9.8 MB 19.6 MB/s eta 0:00:01
   -------------------------- ------------- 6.6/9.8 MB 16.3 MB/s eta 0:00:01
   ------------------------------------- -- 9.2/9.8 MB 15.3 MB/s eta 0:00:01
   ---------------------------------------- 9.8/9.8 MB 14.8 MB/s  0:00:00
   ---------------------------------------- 0.0/23.8 MB ? eta -:--:--
   ----- ---------------------------------- 3.1/23.8 MB 15.2 MB/s eta 0:00:02
   --------- ------------------------------ 5.8/23.8 MB 14.1 MB/s eta 0:00:02
   -------------- ------------------------- 8.4/23.8 MB 13.6 MB/s eta 0:00:02
   ------------------ --------------------- 10.7/23.8 MB 13.2 MB/s eta 0:00:01
   ---------------------- ----------------- 13.4/23.8 MB 13.1 MB/s eta 0:00:01
   -------------------------- ------------- 16.0/23.8 MB 13.2 MB/s eta 0:00:01
   ------------------------------- -------- 18.9/23.8 MB 13.1 MB/s eta 0:00:01
   ---

  Consider adding this directory to PATH or, if you prefer to suppress this warning, use --no-warn-script-location.

[notice] A new release of pip is available: 26.0.1 -> 26.2.1
[notice] To update, run: C:\Users\Kim\AppData\Local\Python\pythoncore-3.14-64\python.exe -m pip install --upgrade pip


In [17]:

import geopandas as gpd

# Load your GeoJSON
gdf = gpd.read_file("export.geojson")

# Convert coordinates to WGS84 (latitude/longitude)
gdf = gdf.to_crs(epsg=4326)

# Use point coordinates or a representative point
# for polygons and other geometries
points = gdf.geometry.representative_point()

gdf["latitude"] = points.y
gdf["longitude"] = points.x

# Remove geometry column and export all attributes
df = gdf.drop(columns="geometry")

df.to_csv("stockholm_poi.csv", index=False, encoding="utf-8-sig")

print(f"Exported {len(df)} locations")
display(df.head())


Exported 4234 locations


,id,@id,access,addr:city,addr:country,addr:floor,addr:housename,addr:housenumber,addr:place,addr:postcode,...,wikidata,wikimedia_commons,wikimedia_commons:path,wikipedia,@relations,year_of_construction,zoo,@geometry,latitude,longitude
0,relation/29368,relation/29368,NaN,Stockholm,SE,NaN,NaN,1,NaN,11152,...,Q648483,NaN,NaN,sv:Stockholms stadshus,NaN,NaN,NaN,center,59.327493,18.054885
1,relation/34394,relation/34394,NaN,Stockholm,SE,NaN,NaN,1,NaN,NaN,...,Q750444,NaN,NaN,sv:Stockholms slott,NaN,NaN,NaN,center,59.326941,18.071628
2,relation/34395,relation/34395,NaN,Stockholm,NaN,NaN,NaN,NaN,NaN,NaN,...,Q1101073,NaN,NaN,sv:Riksdagshuset i Stockholm,NaN,NaN,NaN,center,59.327658,18.068031
3,relation/93398,relation/93398,NaN,Stockholm,NaN,NaN,NaN,NaN,NaN,114 60,...,Q1726607,NaN,NaN,sv:Statens historiska museum,NaN,NaN,NaN,center,59.334846,18.090150
4,relation/279567,relation/279567,NaN,Stockholm,NaN,NaN,NaN,NaN,NaN,NaN,...,Q717105,NaN,NaN,sv:Arvfurstens palats,NaN,1648 / 1783 - 1794,NaN,center,59.329034,18.067564


In [1]:

import pandas as pd

# 1. Load original CSV
df = pd.read_csv("stockholm_poi.csv", low_memory=False)

print(f"Original dataset: {df.shape[0]} rows, {df.shape[1]} columns")

# 2. Rename columns where necessary
df = df.rename(columns={
    "id": "osm_id",
    "addr:street": "street",
    "addr:housenumber": "house_number",
    "addr:postcode": "postcode",
    "addr:city": "city"
})

# 3. Keep relevant columns
columns = [
    "osm_id", "name",
    "amenity", "tourism", "historic", "leisure",
    "latitude", "longitude",
    "street", "house_number", "postcode", "city",
    "website", "contact:website",
    "opening_hours", "wikidata",
    "cuisine", "wheelchair"
]

df = df.reindex(columns=columns)

# 4. Standardize missing values
df = df.replace(r"^\s*$", pd.NA, regex=True)

# 5. Combine alternative website fields
df["website"] = df["website"].fillna(df["contact:website"])
df = df.drop(columns=["contact:website"])

# 6. Validate coordinates
df["latitude"] = pd.to_numeric(df["latitude"], errors="coerce")
df["longitude"] = pd.to_numeric(df["longitude"], errors="coerce")

df = df.dropna(subset=["name", "latitude", "longitude"])

df = df[
    df["latitude"].between(-90, 90) &
    df["longitude"].between(-180, 180)
].copy()

# 7. Create primary category and subcategory
# Priority matters for locations with several tags.
category_columns = ["tourism", "historic", "leisure", "amenity"]

def classify_poi(row):
    for col in category_columns:
        if pd.notna(row[col]):
            return pd.Series({
                "category": col,
                "subcategory": row[col]
            })
    return pd.Series({
        "category": "other",
        "subcategory": "unknown"
    })

df[["category", "subcategory"]] = df.apply(classify_poi, axis=1)

# 8. Remove duplicate OpenStreetMap identifiers
df = df.drop_duplicates(subset=["osm_id"])

# 9. Reorder columns
ordered = [
    "osm_id", "name", "category", "subcategory",
    "amenity", "tourism", "historic", "leisure",
    "latitude", "longitude",
    "street", "house_number", "postcode", "city",
    "website", "opening_hours",
    "wikidata", "cuisine", "wheelchair"
]

df = df[ordered].reset_index(drop=True)

# 10. Save cleaned dataset
df.to_csv(
    "stockholm_poi_cleaned.csv",
    index=False,
    encoding="utf-8-sig"
)

print(f"Cleaned dataset: {df.shape[0]} rows, {df.shape[1]} columns")
print("\nCategory distribution:")
print(df["category"].value_counts())

display(df.head(10))


Original dataset: 4234 rows, 438 columns
Cleaned dataset: 4234 rows, 19 columns

Category distribution:
category
amenity     2802
tourism      705
leisure      530
historic     197
Name: count, dtype: int64


,osm_id,name,category,subcategory,amenity,tourism,historic,leisure,latitude,longitude,street,house_number,postcode,city,website,opening_hours,wikidata,cuisine,wheelchair
0,relation/29368,Stockholms stadshus,historic,townhall,townhall,NaN,townhall,NaN,59.327493,18.054885,Hantverkargatan,1,11152,Stockholm,https://stadshuset.stockholm/,NaN,Q648483,NaN,yes
1,relation/34394,Stockholms slott,tourism,attraction,NaN,attraction,castle,NaN,59.326941,18.071628,Slottsbacken,1,NaN,Stockholm,https://www.kungligaslotten.se,NaN,Q750444,NaN,NaN
2,relation/34395,Riksdagshuset,historic,building,NaN,NaN,building,NaN,59.327658,18.068031,NaN,NaN,NaN,Stockholm,NaN,NaN,Q1101073,NaN,NaN
3,relation/93398,Historiska museet,tourism,museum,NaN,museum,NaN,NaN,59.334846,18.090150,NaN,NaN,114 60,Stockholm,https://www.historiska.se,"Tu, Th-Su 11:00-17:00; We 11:00-20:00",Q1726607,NaN,yes
4,relation/279567,Arvfurstens palats,historic,castle,NaN,NaN,castle,NaN,59.329034,18.067564,NaN,NaN,NaN,Stockholm,NaN,NaN,Q717105,NaN,NaN
5,relation/417898,Ålstensskogen,leisure,park,NaN,NaN,NaN,park,59.316931,17.954309,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
6,relation/1636106,Ulvsunda slott,historic,palace,NaN,NaN,palace,NaN,59.340869,17.964075,NaN,NaN,NaN,NaN,NaN,NaN,Q931176,NaN,NaN
7,way/2117275,Ekensbergs Båtsällskap,leisure,marina,NaN,NaN,NaN,marina,59.313256,17.992587,NaN,NaN,NaN,NaN,http://ekensbergsbs.se/,NaN,NaN,NaN,NaN
8,relation/2171352,Bååtska palatset,historic,castle,NaN,NaN,castle,NaN,59.330545,18.076438,NaN,NaN,NaN,NaN,NaN,NaN,Q10438659,NaN,NaN
9,relation/2440883,Hallwylska palatset,tourism,museum,NaN,museum,castle,NaN,59.333277,18.074528,Hamngatan,4,111 47,Stockholm,https://hallwylskamuseet.se/,"Tu, Th-Fr 12:00-16:00; We 12:00-19:00; Sa-Su 1...",Q4346239,NaN,NaN
